In [1]:
import json
import codecs
import datetime
import os.path
import argparse
import csv
from instagrapi import Client
import time


In [2]:

def create_map_link(coordinates):
    if len(str(coordinates[0])) > 0 and len(str(coordinates[1])) > 0:
        return 'https://www.google.com/maps?q=' + str(coordinates[0]) + ',' + str(coordinates[1])
    else:
        return ''

def to_json(python_object):
    if isinstance(python_object, bytes):
        return {
            "__class__": "bytes",
            "__value__": codecs.encode(python_object, "base64").decode(),
        }
    raise TypeError(repr(python_object) + " is not JSON serializable")

def from_json(json_object):
    if "__class__" in json_object and json_object["__class__"] == "bytes":
        return codecs.decode(json_object["__value__"].encode(), "base64")
    return json_object

def onlogin_callback(api, new_settings_file):
    cache_settings = api.get_settings()
    with open(new_settings_file, "w") as outfile:
        json.dump(cache_settings, outfile, default=to_json)
        print("SAVED: {0!s}".format(new_settings_file))

In [7]:
class User:
    def __init__(self, username, password, collection_id):
        self.username = username  # Initialize the username attribute
        self.password = password
        self.collection_id = collection_id



# Create an instance of the User class
args = User(username="marmargrobe",
        password="Alejapierdole23!",
        collection_id="123")

'marmargrobe'

In [66]:
settings_file = "credentials.json"
api = Client()

if os.path.isfile(settings_file):
    with open(settings_file) as file_data:
        cached_settings = json.load(file_data, object_hook=from_json)
    print("Reusing settings: {0!s}".format(settings_file))
    api.set_settings(cached_settings)
    api.login(args.username, args.password)
else:
    # Login and save session
    api.login(args.username, args.password)
    onlogin_callback(api, settings_file)
# Display cookie expiry
cookie_expiry = datetime.datetime.fromtimestamp(api.cookie_dict.get('auth_expires', 0))
print("Cookie Expiry: {0!s}".format(cookie_expiry.strftime("%Y-%m-%dT%H:%M:%SZ")))

print("==== Starting to fetch saved posts data ====")

saved_collection = []

Reusing settings: credentials.json
Cookie Expiry: 1969-12-31T16:00:00Z
==== Starting to fetch saved posts data ====


In [61]:
user_id = api.user_id


In [21]:
## content that is shared by me
# pinned_content = api.user_pinned_medias(user_id)
# user_media = api.user_medias(user_id)
# pinned_content[0]
# user_media_v1= api.user_medias_v1(user_id)


In [44]:
## content that i saved

In [67]:
all_collections = api.collections()

In [70]:
all_collections

[Collection(id='ALL_MEDIA_AUTO_COLLECTION', name='All posts', type='ALL_MEDIA_AUTO_COLLECTION', media_count=6809),
 Collection(id='17994803555546278', name='Travel Ags and Mars', type='MEDIA', media_count=48),
 Collection(id='17868916941058808', name='Journals', type='MEDIA', media_count=7),
 Collection(id='18037718579332817', name='Movies', type='MEDIA', media_count=11),
 Collection(id='17863087068256775', name='Europe purchases', type='MEDIA', media_count=1),
 Collection(id='18073547749454486', name='Recipes ', type='MEDIA', media_count=30),
 Collection(id='PRODUCT_AUTO_COLLECTION', name='Shops products', type='PRODUCT_AUTO_COLLECTION', media_count=3),
 Collection(id='18006209423336410', name='Projects', type='MEDIA', media_count=42),
 Collection(id='18032430034769021', name='Workouts', type='MEDIA', media_count=32),
 Collection(id='18029168378517322', name='Make up', type='MEDIA', media_count=1),
 Collection(id='18023689022110198', name='Tattoos', type='MEDIA', media_count=1),
 Coll

In [71]:
all_posts = api.collection_medias_by_name("All posts")
# only returns 21

In [72]:
all_posts_pk = api.collection_pk_by_name("All posts")

In [74]:

def fetch_all_saved_medias(api, collection_pk, total_medias):
    all_medias = []
    last_media_pk = 0
    batch_size = 100  # Adjust the batch size as necessary

    while len(all_medias) < total_medias:
        # Fetch the media for the current batch
        medias = api.collection_medias(collection_pk, amount=batch_size, last_media_pk=last_media_pk)

        if not medias:
            print("No more media to fetch.")
            break  # Exit the loop if no more media is returned

        all_medias.extend(medias)
        
        # Update the last media pk for pagination
        last_media_pk = medias[-1].pk  # Assuming Media object has 'pk' attribute

        print(f"Fetched {len(medias)} media items. Total collected: {len(all_medias)}")

        # Optional: Add a delay to avoid hitting rate limits
        time.sleep(1)  # Sleep for 1 second

    return all_medias


In [73]:
total_medias = 6809

In [75]:
all_saved_medias = fetch_all_saved_medias(api, all_posts_pk, total_medias)


Fetched 100 media items. Total collected: 100
Fetched 99 media items. Total collected: 199
Fetched 98 media items. Total collected: 297
Fetched 97 media items. Total collected: 394
Fetched 96 media items. Total collected: 490
Fetched 95 media items. Total collected: 585
Fetched 94 media items. Total collected: 679
Fetched 93 media items. Total collected: 772
Fetched 92 media items. Total collected: 864
Fetched 91 media items. Total collected: 955
Fetched 90 media items. Total collected: 1045
Fetched 89 media items. Total collected: 1134
Fetched 88 media items. Total collected: 1222
Fetched 87 media items. Total collected: 1309
Fetched 86 media items. Total collected: 1395
Fetched 85 media items. Total collected: 1480
Fetched 84 media items. Total collected: 1564
Fetched 83 media items. Total collected: 1647
Fetched 82 media items. Total collected: 1729
Fetched 81 media items. Total collected: 1810
Fetched 80 media items. Total collected: 1890
Fetched 79 media items. Total collected: 19

In [76]:
# all_posts_medias = api.collection_medias(all_posts_pk, amount=0)
# toget all

In [77]:

for media in all_saved_medias:
    saved_collection.append(media.dict())


In [78]:

field_names = saved_collection[0].keys()

count = 0
res = []

print("==== Saving data to file ====")


==== Saving data to file ====


In [79]:
for v in saved_collection[0].keys():
    print(v)

pk
id
code
taken_at
media_type
image_versions2
product_type
thumbnail_url
location
user
comment_count
comments_disabled
commenting_disabled_for_viewer
like_count
play_count
has_liked
caption_text
accessibility_caption
usertags
sponsor_tags
video_url
view_count
video_duration
title
resources
clips_metadata


In [83]:

for media in saved_collection:
    count += 1
    media["#"] = count
    res.append(media)


In [84]:
res

[{'pk': 3494684183526379300,
  'id': '3494684183526379300_1454459300',
  'code': 'DB_nL_RRA8k',
  'taken_at': datetime.datetime(2024, 11, 5, 15, 0, tzinfo=TzInfo(UTC)),
  'media_type': 2,
  'image_versions2': {'candidates': [{'width': 360,
     'height': 640,
     'url': 'https://scontent-sjc3-1.cdninstagram.com/v/t51.29350-15/465690150_870791631912760_7917230422796849259_n.jpg?stp=dst-jpg_e15_p360x360&efg=eyJ2ZW5jb2RlX3RhZyI6ImltYWdlX3VybGdlbi43MjB4MTI4MC5zZHIuZjI5MzUwLmRlZmF1bHRfY292ZXJfZnJhbWUifQ&_nc_ht=scontent-sjc3-1.cdninstagram.com&_nc_cat=104&_nc_ohc=YaHOeX-VeQAQ7kNvgEzY4Co&_nc_gid=423fa7598c11401d8f6c43761db00b05&edm=ACOOH6wBAAAA&ccb=7-5&ig_cache_key=MzQ5NDY4NDE4MzUyNjM3OTMwMA%3D%3D.3-ccb7-5&oh=00_AYDnHPpMmfh-dpqTspJ8FmI2A3eAOdP6r7n5GVN-Q_WNiQ&oe=673037DE&_nc_sid=aa4e97',
     'scans_profile': 'e15'}],
   'additional_candidates': {'igtv_first_frame': {'width': 360,
     'height': 639,
     'url': 'https://scontent-sjc3-1.cdninstagram.com/v/t51.2885-15/465623452_906067211628547

In [87]:

with open('./data/all_posts.csv', "w", encoding="utf-8") as csvfile:
    writer = csv.DictWriter(csvfile, fieldnames=field_names)
    writer.writeheader()
    writer.writerows(res)

In [ ]:

for media in api.saved_medias():
    saved_collection.append(media.dict())

field_names = [
    "#",
    "link",
    "location_short_name",
    "facebook_places_id",
    "location_name",
    "address",
    "city",
    "location_lng",
    "location_lat",
    "location_map_link",
    "lng",
    "lat",
    "map_link",
    "full_name_op",
    "username_op",
    "caption",
]

count = 0
res = []

print("==== Saving data to file ====")

for media in saved_collection:
    if args.collection in media.get("saved_collection_ids", []):
        count += 1
        location = media.get("location", {})
        res.append({
            "#": count,
            "link": "https://www.instagram.com/p/" + media.get("code"),
            "location_short_name": location.get("short_name", ""),
            "facebook_places_id": location.get("facebook_places_id", ""),
            "location_name": location.get("name", ""),
            "address": location.get("address", ""),
            "city": location.get("city", ""),
            "location_lng": location.get("lng", ""),
            "location_lat": location.get("lat", ""),
            "location_map_link": create_map_link([location.get("lat", ""), location.get("lng", "")]),
            "lng": media.get("lng", ""),
            "lat": media.get("lat", ""),
            "map_link": create_map_link([media.get("lat", ""), media.get("lng", "")]),
            "full_name_op": media.get("user", {}).get("full_name", ""),
            "username_op": media.get("user", {}).get("username", ""),
            "caption": media.get("caption_text", ""),
        })

with open(args.output, "w", encoding="utf-8") as csvfile:
    writer = csv.DictWriter(csvfile, fieldnames=field_names)
    writer.writeheader()
    writer.writerows(res)